### Dataset and Task Metadata

In [1]:
from data_foundry.schema import DatasetMetadata, PredictiveMLTaskMetadata

dataset_mold = DatasetMetadata(
    unique_name="nci_prostate_cancer",
    dataset_year="2002",
    domain_str="medical & healthcare",
    # Data Source
    dataset_source="GOV Website",
    original_dataset_source_download_link="https://home.ccr.cancer.gov/ncifdaproteomics/ppatterns.asp",
    download_description="""
We download the data to a predefined folder.

mkdir -p local-data-warehouse/nci_prostate_cancer && wget -P local-data-warehouse/nci_prostate_cancer https://home.ccr.cancer.gov/ncifdaproteomics/JNCI_Data_7-3-02.zip && unzip local-data-warehouse/nci_prostate_cancer/JNCI_Data_7-3-02.zip -d local-data-warehouse/nci_prostate_cancer/ && rm local-data-warehouse/nci_prostate_cancer/JNCI_Data_7-3-02.zip
""",
    # References
    academic_reference_bibtex="""@article{Petricoin2002SerumPP,
  title={Serum Proteomic Patterns for Detection of Prostate Cancer},
  author={Emanuel F. Petricoin and David K. Ornstein and Cloud P. Paweletz and Ali Ardekani and Paul S. Hackett and Ben A. Hitt and Alfredo Velassco and Christian Trucco and Laura Wiegand and Kamillah Wood and Charles B. Simone and Peter J. Levine and W. Marston Linehan and Michael R. Emmert-Buck and Seth M. Steinberg and Elise C. Kohn and Lance A. Liotta},
  journal={JNCI: Journal of the National Cancer Institute},
  year={2002},
  volume={94},
  number={20},
  pages={1576-1578},
  doi={10.1093/jnci/94.20.1576},
  url={https://doi.org/10.1093/jnci/94.20.1576}
}
""",
    academic_reference_bibtex_key="Petricoin2002SerumPP",
    license="Public Domain",
    data_tags=["IID"],
    curation_comments="""
        - We merge all samples located in the .csv files into one DataFrame.
        - We label the samples based on name of the folder they are located in: "Benign PSA Greater 4" and "No Evidence of Disease PSA Less 1" consitute healthy patient cases while "Prostate Cancer (..)" samples point to individuals with a prostate cancer. This distinction is made based on the original reference and the prediction task mentioned in it (tumor vs healthy).
        - We shuffle the data since it is concatenated in the folders order.
    """,
)
task_mold = PredictiveMLTaskMetadata(
    target_column_name="HasCancer",
    problem_type="binary_classification",
    objective_metric_name="roc_auc",
    stratify_on="HasCancer",
)

## Preprocessing

In [2]:
import os
import pandas as pd

valid_labels = {
    "Benign PSA Greater 4",
    "No Evidence of Disease PSA Less 1",
    "Prostate Cancer PSA 4-10",
    "Prostate Cancer PSA Greater 10"
}

def csv_to_dataframe(file, label):
    """
    Convert each sample from the .csv file to a DataFrame with a label based on the name of the folder it is located in. 
    """
    label_map = {
        "Benign PSA Greater 4": "No",
        "No Evidence of Disease PSA Less 1": "No",
        "Prostate Cancer PSA 4-10": "Yes",
        "Prostate Cancer PSA Greater 10": "Yes"
    }

    df = pd.read_csv(file).T
    df.reset_index(drop=True, inplace=True)
    df.drop(0, inplace=True)

    target_feature = "HasCancer"
    df.columns = [f"Attribute {i+1}" for i in range(len(df.columns) - 1)] + [target_feature]
    df[target_feature] = label_map.get(label, label)

    return df

r = {}
subdirs = [dirs[0] for dirs in os.walk(dataset_mold.path)][1:]
for subdir in subdirs:
    label = subdir.split("/")[-1]
    _, _, files = next(os.walk(subdir))
    r[label] = [os.path.join(subdir, name) for name in files]

df = pd.concat(
        [csv_to_dataframe(filepath, label) for label in r if label in valid_labels for filepath in r[label]], 
        ignore_index=True
    )
df["HasCancer"] = df["HasCancer"].astype("category")
df = df.sample(frac=1, random_state=99).reset_index(drop=True)

## Data Checks

In [3]:
from data_foundry import dataset_checks
df_head, summary, numeric_stats, cat_stats, target_df = dataset_checks.run_all_checks(
    data=df,
    classification=task_mold.is_classification,
    target_feature=task_mold.target_column_name,
    print_report=False, # In notebook...
)


#### Dataset Overview
Rows: 322
Columns: 15154
Use sampling: False (sample size: 322)
Get row duplicates (staged, merged)...
Using top-10 columns for initial filtering: ['Attribute 7577', 'Attribute 10073', 'Attribute 10061', 'Attribute 10062', 'Attribute 10063', 'Attribute 10064', 'Attribute 10065', 'Attribute 10066', 'Attribute 10067', 'Attribute 10068']
Rows remaining as candidates after top-10 filter: 0 (of 322)

#### Duplicate Report
Total duplicate rows: 0 (0.00% of dataset)
Duplicate rows ignoring target: 0 (0.00% of dataset)
Get column duplicates...
Duplicate columns: 0 (0.00% of columns)

Data quality checks completed.


In [4]:
# Sample Rows
df_head

,Attribute 1,Attribute 2,Attribute 3,Attribute 4,Attribute 5,Attribute 6,Attribute 7,Attribute 8,Attribute 9,Attribute 10,Attribute 11,Attribute 12,Attribute 13,Attribute 14,Attribute 15,Attribute 16,Attribute 17,Attribute 18,Attribute 19,Attribute 20,Attribute 21,Attribute 22,Attribute 23,Attribute 24,Attribute 25,Attribute 26,Attribute 27,Attribute 28,Attribute 29,Attribute 30,Attribute 31,Attribute 32,Attribute 33,Attribute 34,Attribute 35,Attribute 36,Attribute 37,Attribute 38,Attribute 39,Attribute 40,Attribute 41,Attribute 42,Attribute 43,Attribute 44,Attribute 45,Attribute 46,Attribute 47,Attribute 48,Attribute 49,Attribute 50,Attribute 51,Attribute 52,Attribute 53,Attribute 54,Attribute 55,Attribute 56,Attribute 57,Attribute 58,Attribute 59,Attribute 60,Attribute 61,Attribute 62,Attribute 63,Attribute 64,Attribute 65,Attribute 66,Attribute 67,Attribute 68,Attribute 69,Attribute 70,Attribute 71,Attribute 72,Attribute 73,Attribute 74,Attribute 75,Attribute 76,Attribute 77,Attribute 78,Attribute 79,Attribute 80,Attribute 81,Attribute 82,Attribute 83,Attribute 84,Attribute 85,Attribute 86,Attribute 87,Attribute 88,Attribute 89,Attribute 90,Attribute 91,Attribute 92,Attribute 93,Attribute 94,Attribute 95,Attribute 96,Attribute 97,Attribute 98,Attribute 99,Attribute 100,Attribute 101,Attribute 102,Attribute 103,Attribute 104,Attribute 105,Attribute 106,Attribute 107,Attribute 108,Attribute 109,Attribute 110,Attribute 111,Attribute 112,Attribute 113,Attribute 114,Attribute 115,Attribute 116,Attribute 117,Attribute 118,Attribute 119,Attribute 120,Attribute 121,Attribute 122,Attribute 123,Attribute 124,Attribute 125,Attribute 126,Attribute 127,Attribute 128,Attribute 129,Attribute 130,Attribute 131,Attribute 132,Attribute 133,Attribute 134,Attribute 135,Attribute 136,Attribute 137,Attribute 138,Attribute 139,Attribute 140,Attribute 141,Attribute 142,Attribute 143,Attribute 144,Attribute 145,Attribute 146,Attribute 147,Attribute 148,Attribute 149,Attribute 150,Attribute 151,Attribute 152,Attribute 153,Attribute 154,Attribute 155,Attribute 156,Attribute 157,Attribute 158,Attribute 159,Attribute 160,Attribute 161,Attribute 162,Attribute 163,Attribute 164,Attribute 165,Attribute 166,Attribute 167,Attribute 168,Attribute 169,Attribute 170,Attribute 171,Attribute 172,Attribute 173,Attribute 174,Attribute 175,Attribute 176,Attribute 177,Attribute 178,Attribute 179,Attribute 180,Attribute 181,Attribute 182,Attribute 183,Attribute 184,Attribute 185,Attribute 186,Attribute 187,Attribute 188,Attribute 189,Attribute 190,Attribute 191,Attribute 192,Attribute 193,Attribute 194,Attribute 195,Attribute 196,Attribute 197,Attribute 198,Attribute 199,Attribute 200,Attribute 201,Attribute 202,Attribute 203,Attribute 204,Attribute 205,Attribute 206,Attribute 207,Attribute 208,Attribute 209,Attribute 210,Attribute 211,Attribute 212,Attribute 213,Attribute 214,Attribute 215,Attribute 216,Attribute 217,Attribute 218,Attribute 219,Attribute 220,Attribute 221,Attribute 222,Attribute 223,Attribute 224,Attribute 225,Attribute 226,Attribute 227,Attribute 228,Attribute 229,Attribute 230,Attribute 231,Attribute 232,Attribute 233,Attribute 234,Attribute 235,Attribute 236,Attribute 237,Attribute 238,Attribute 239,Attribute 240,Attribute 241,Attribute 242,Attribute 243,Attribute 244,Attribute 245,Attribute 246,Attribute 247,Attribute 248,Attribute 249,Attribute 250,Attribute 251,Attribute 252,Attribute 253,Attribute 254,Attribute 255,Attribute 256,Attribute 257,Attribute 258,Attribute 259,Attribute 260,Attribute 261,Attribute 262,Attribute 263,Attribute 264,Attribute 265,Attribute 266,Attribute 267,Attribute 268,Attribute 269,Attribute 270,Attribute 271,Attribute 272,Attribute 273,Attribute 274,Attribute 275,Attribute 276,Attribute 277,Attribute 278,Attribute 279,Attribute 280,Attribute 281,Attribute 282,Attribute 283,Attribute 284,Attribute 285,Attribute 286,Attribute 287,Attribute 288,Attribute 289,Attribute 290,Attribute 291,Attribute 292,Attribute 293,Attri

In [5]:
# Feature Summary
summary

,index,dtype,n_missing,pct_missing,n_unique,examples
0,HasCancer,category,0.0,0.0,2.0,"No, Yes"
1,Attribute 1,float64,0.0,0.0,285.0,"-0.587, -0.5048, -0.3959, -0.5638, -0.4809, -0.4621, -0.5054, -0.4408, -0.4292, -0.3341"
2,Attribute 2,float64,0.0,0.0,293.0,"-0.3969, -0.3479, -0.2268, -0.4439, -0.4179, -0.3134, -0.5371, -0.4273, -0.4445, -0.3944"
3,Attribute 3,float64,0.0,0.0,296.0,"-0.2463, -0.2071, -0.2303, -0.1299, -0.1205, -0.1368, -0.3366, -0.314, -0.1111, -0.2538"
4,Attribute 4,float64,0.0,0.0,301.0,"-0.4897, -0.4806, -0.4813, -0.5001, -0.5249, -0.5365, -0.4376, -0.5299, -0.4762, -0.4612"
5,Attribute 5,float64,0.0,0.0,306.0,"-0.3203, 0.309, -0.1073, 0.5704, 0.0351, 0.2795, -0.1475, -0.3671, -0.3432, -0.2924"
6,Attribute 6,float64,0.0,0.0,300.0,"0.3956, 0.6535, 0.6275, 0.8056, 0.6613, 0.4223, 0.5192, 0.181, 0.3821, 0.5747"
7,Attribute 7,float64,0.0,0.0,298.0,"-2.3322, -2.389, -2.342, -2.2984, -2.3498, -2.3777, -2.394, -2.3802, -2.4107, -2.2463"
8,Attribute 8,float64,0.0,0.0,318.0,"-2.4044, -2.5522, -2.5518, -1.7895, -2.0772, -2.0339, -2.3103, -2.5355, -2.31, -2.1352"
9,Attribute 9,float64,0.0,0.0,304.0,"-3.3534, -3.4469, -3.1799, -3.3672, -3.0253, -3.2445, -3.1238, -3.2147, -3.1639, -3.2609"


In [6]:
# Numeric Feature Statistics
numeric_stats

,count,mean,std,min,max
Attribute 1,322.0,-0.494827,0.106947,-8.235294e-01,-0.255059
Attribute 2,322.0,-0.382047,0.105963,-6.782745e-01,-0.062745
Attribute 3,322.0,-0.207261,0.165060,-6.996078e-01,0.315922
Attribute 4,322.0,-0.504110,0.173254,-1.002667e+00,0.283294
Attribute 5,322.0,0.040922,0.403977,-6.208628e-01,1.879843
Attribute 6,322.0,0.523806,0.251295,-1.010196e-01,1.785098
Attribute 7,322.0,-2.315721,0.184735,-2.666667e+00,-1.081412
Attribute 8,322.0,-2.249967,0.376601,-2.841782e+00,-0.818196
Attribute 9,322.0,-3.215894,0.222523,-3.837490e+00,-2.260392
Attribute 10,322.0,-3.761795,0.160880,-4.091294e+00,-2.697098


In [7]:
# Categorical Feature Statistics
cat_stats

value  count    pct
column    rank                    
HasCancer 1       No    253  78.57
          2      Yes     69  21.43

In [8]:
# Target Distribution
target_df

,count,pct
HasCancer,,
No,253,78.57
Yes,69,21.43


## Task Curation

In [9]:
from data_foundry.curation_recommendations import get_recommended_splits_dimensions

n_repeats, n_splits, none_or_test_size = get_recommended_splits_dimensions(
    dataset=df,
    group_on=task_mold.group_on,
    time_on=task_mold.time_on,
)
print(f"Recommended splits: n_repeats={n_repeats}, n_splits={n_splits}, test_size={none_or_test_size}")

Recommended splits: n_repeats=20, n_splits=3, test_size=None


In [10]:
from data_foundry.schema import PredictiveMLSplitsMetadata
from data_foundry import curation_recommendations

splits = curation_recommendations.get_recommended_iid_splits(
    dataset=df,
    n_repeats=n_repeats,
    n_splits=n_splits,
    test_size=none_or_test_size,
    stratify_on=task_mold.stratify_on,
)

splits_mold = PredictiveMLSplitsMetadata(
    splits_comment="Default splits.",
    splits=splits,
)

Using Stratified IID splits.


## Export

In [11]:
from data_foundry.curation_container import CuratedContainer
curated_data = CuratedContainer(
    dataset=df,
    dataset_metadata=dataset_mold,
    task_metadata=task_mold,
    experiment_metadata=splits_mold,
 )
curated_data.save()
print(curated_data.uuid)
print(curated_data.checksum)

Calculating checksum for curated container...
Saving curated container to nci_prostate_cancer/019d9d25-7536-7943-b1b1-deee060a4115
019d9d25-7536-7943-b1b1-deee060a4115
c67ba87df9962384003d4610c6f81dfebb2fad76822369aa947db9220d38880c
